In [6]:
import pandas as pd
import numpy as np
import os

# 📂 文件路径
base_path = r"F:\TUB\greenlandProject\ERA5LAND\snowalbedo"
albedo_file = r"F:\TUB\greenlandProject\NEWdataverse_files\allsites_albedoYM_lonlai.csv"
output_file = r"F:\TUB\greenlandProject\ERA5LAND\snowalbedo\all_stations_snowbilinear.csv"

# 读取所有站点数据（包含经纬度）
albedo_df = pd.read_csv(albedo_file, dtype=str)

# 统一 `station` 格式，确保站点名称正确匹配
albedo_df['station'] = albedo_df['station'].str.strip().str.upper()

# 自动修正 `valid_time` 并确保格式匹配
albedo_df['valid_time'] = albedo_df['valid_time'].str.strip()
albedo_df['valid_time'] = pd.to_datetime(albedo_df['valid_time'], errors='coerce').dt.strftime('%Y-%m-%d')

# 确保经纬度为数值类型
albedo_df['longitude'] = albedo_df['longitude'].astype(float)
albedo_df['latitude'] = albedo_df['latitude'].astype(float)

print("\n✅ 站点数据（前 5 行）：")
print(albedo_df.head())

# 存储计算结果
results = []

# =============== 这里是主循环，所有 continue 都写在这个for里 ===============
for index, row in albedo_df.iterrows():
    month = str(row['valid_time']).strip()  # 确保 `month` 是字符串
    station = row['station']
    asn_value = row['asn']
    lat = row['latitude']
    lon = row['longitude']
    missing_reason = ""  # 用于记录可能的异常信息

    # 先检查当前记录的年份
    try:
        year = int(month[:4])
    except ValueError:
        missing_reason = "Invalid valid_time format"
        results.append({
            'station': station, 
            'valid_time': month, 
            'asn': asn_value, 
            'interp_asn': np.nan, 
            'missing': missing_reason
        })
        continue

    # 拼出当年的 asn 文件路径
    asn_file = os.path.join(base_path, f"snowAlbedo_{year}_grid.csv")

    if not os.path.exists(asn_file):
        missing_reason = f"snowAlbedo file {year} missing"
        results.append({
            'station': station, 
            'valid_time': month, 
            'asn': asn_value, 
            'interp_asn': np.nan, 
            'missing': missing_reason
        })
        continue

    # 读取当年的 asn 数据
    asn_df = pd.read_csv(asn_file, dtype=str)

    # 修正 asn_df 里的 valid_time
    asn_df['valid_time'] = asn_df['valid_time'].str.strip()
    asn_df['valid_time'] = pd.to_datetime(asn_df['valid_time'], errors='coerce').dt.strftime('%Y-%m-%d')

    # 找对应 month 的数据
    asn_month_data = asn_df[asn_df['valid_time'] == month]

    if asn_month_data.empty:
        print(f"\n⚠️ `{month}` 没有数据，自动寻找最近的可用日期...")
        available_dates = asn_df['valid_time'].dropna().unique()
        if len(available_dates) > 0:
            # 寻找最接近 month 的日期
            nearest_date = min(
                available_dates, 
                key=lambda x: abs(pd.Timestamp(month) - pd.Timestamp(x))
            )
            asn_month_data = asn_df[asn_df['valid_time'] == nearest_date]
            print(f"⚠️  `valid_time` 替换为 {nearest_date}")
        else:
            missing_reason = "No available snowAlbedo dates"
            results.append({
                'station': station, 
                'valid_time': month, 
                'asn': asn_value, 
                'interp_asn': np.nan, 
                'missing': missing_reason
            })
            continue

    print(f"\n✅ `snowAlbedo_{year}_grid.csv` 找到 valid_time == {month} 的数据量: {len(asn_month_data)}")

    # 确保 asn_month_data 字段为 float
    asn_month_data['latitude'] = asn_month_data['latitude'].astype(float)
    asn_month_data['longitude'] = asn_month_data['longitude'].astype(float)
    asn_month_data['asn'] = asn_month_data['asn'].astype(float)

    # 计算每个网格点到站点的距离
    asn_month_data['distance'] = np.sqrt(
        (asn_month_data['latitude'] - lat)**2 + 
        (asn_month_data['longitude'] - lon)**2
    )

    # 选出最近的 4 个点
    nearest_points = asn_month_data.nsmallest(4, 'distance')

    if len(nearest_points) < 4:
        missing_reason = "Not enough grid points"
        results.append({
            'station': station,
            'valid_time': month,
            'asn': asn_value,
            'interp_asn': np.nan,
            'missing': missing_reason
        })
        continue

    print(f"\n✅ 站点 `{station}` `{month}` 的 4 个最近网格点：")
    print(nearest_points[['latitude', 'longitude', 'asn', 'distance']])

    # =============== 双线性插值部分（带防护）开始 ===============
    # 1) 取这4个点中最小/最大纬度、经度 => 构成矩形四角
    points_arr = nearest_points[['latitude', 'longitude']].values  # shape = (4, 2)
    lat1, lat2 = np.min(points_arr[:,0]), np.max(points_arr[:,0])
    lon1, lon2 = np.min(points_arr[:,1]), np.max(points_arr[:,1])

    # 若无法形成非退化矩形（lat1 == lat2或lon1 == lon2），退出
    if (lat2 == lat1) or (lon2 == lon1):
        missing_reason = "Invalid rectangle (lat1==lat2 or lon1==lon2)"
        results.append({
            'station': station,
            'valid_time': month,
            'asn': asn_value,
            'interp_asn': np.nan,
            'missing': missing_reason
        })
        continue

    # 2) 查找四个角对应的asn: (lat1, lon1)=f11; (lat2, lon1)=f21; (lat1, lon2)=f12; (lat2, lon2)=f22
    def find_corner_value(lc, lo):
        sub = nearest_points.copy()
        sub['dist_corner'] = np.sqrt((sub['latitude']-lc)**2 + (sub['longitude']-lo)**2)
        sub = sub.nsmallest(1, 'dist_corner')
        return sub['asn'].values[0]  # 若最近点也是 NaN，就返回 NaN

    f11 = find_corner_value(lat1, lon1)
    f21 = find_corner_value(lat2, lon1)
    f12 = find_corner_value(lat1, lon2)
    f22 = find_corner_value(lat2, lon2)

    # 若任意一个角是 NaN，就无法准确双线性插值
    if any(np.isnan([f11, f21, f12, f22])):
        missing_reason = "Corner asn has NaN"
        results.append({
            'station': station,
            'valid_time': month,
            'asn': asn_value,
            'interp_asn': np.nan,
            'missing': missing_reason
        })
        continue

    # 3) 双线性插值公式
    x, y = lat, lon  # 目标点
    denominator = (lat2 - lat1) * (lon2 - lon1)

    # 如果分母过小，可能导致数值错误
    if abs(denominator) < 1e-15:
        missing_reason = "Denominator too small for bilinear"
        results.append({
            'station': station,
            'valid_time': month,
            'asn': asn_value,
            'interp_asn': np.nan,
            'missing': missing_reason
        })
        continue

    interp_asn = (
        (lat2 - x)*(lon2 - y)*f11 +
        (x - lat1)*(lon2 - y)*f21 +
        (lat2 - x)*(y - lon1)*f12 +
        (x - lat1)*(y - lon1)*f22
    ) / denominator

    # 判断结果是否为 NaN/Inf
    if np.isnan(interp_asn) or np.isinf(interp_asn):
        missing_reason = "Bilinear resulted in NaN or Inf"
        interp_asn = np.nan
        # 你若仍想保留一个数值，可加兜底：interp_asn = np.mean([f11,f21,f12,f22]) 等

    # =============== 双线性插值部分结束 ===============

    # 记录结果
    results.append({
        'station': station,
        'valid_time': month,
        'asn': asn_value,
        'interp_asn': interp_asn,
        'missing': missing_reason
    })

# =============== for循环结束，这里没有再写任何continue ===============

# 转换为 DataFrame
results_df = pd.DataFrame(results)
results_df.to_csv(output_file, index=False)

print(f"\n✅ 计算完成！所有插值结果已保存至: {output_file}")



✅ 站点数据（前 5 行）：
   valid_time station     asn  longitude   latitude
0  1995-06-01     CEN  0.8412 -61.115896  77.181945
1  1995-07-01     CEN  0.8254 -61.115896  77.181945
2  1995-08-01     CEN  0.8349 -61.115896  77.181945
3  1995-09-01     CEN    0.87 -61.115896  77.181945
4  1996-04-01     CEN    0.83 -61.115896  77.181945

✅ `snowAlbedo_1995_grid.csv` 找到 valid_time == 1995-06-01 的数据量: 177

✅ 站点 `CEN` `1995-06-01` 的 4 个最近网格点：
     latitude  longitude       asn  distance
905      77.2      -61.1  0.850002  0.024055
907      77.1      -61.1  0.850002  0.083473
906      77.2      -61.0  0.850002  0.117294
908      77.1      -61.0  0.850002  0.141940

✅ `snowAlbedo_1995_grid.csv` 找到 valid_time == 1995-07-01 的数据量: 177

✅ 站点 `CEN` `1995-07-01` 的 4 个最近网格点：
      latitude  longitude       asn  distance
1082      77.2      -61.1  0.850002  0.024055
1084      77.1      -61.1  0.850002  0.083473
1083      77.2      -61.0  0.850002  0.117294
1085      77.1      -61.0  0.850002  0.141940

✅ `sno

C:\Users\11823\AppData\Local\Temp\ipykernel_15768\2457463173.py:102: SettingWithCopyWarning: 
A value is trying to be set on a copy of a slice from a DataFrame.
Try using .loc[row_indexer,col_indexer] = value instead

See the caveats in the documentation: https://pandas.pydata.org/pandas-docs/stable/user_guide/indexing.html#returning-a-view-versus-a-copy
  asn_month_data['latitude'] = asn_month_data['latitude'].astype(float)
C:\Users\11823\AppData\Local\Temp\ipykernel_15768\2457463173.py:103: SettingWithCopyWarning: 
A value is trying to be set on a copy of a slice from a DataFrame.
Try using .loc[row_indexer,col_indexer] = value instead

See the caveats in the documentation: https://pandas.pydata.org/pandas-docs/stable/user_guide/indexing.html#returning-a-view-versus-a-copy
  asn_month_data['longitude'] = asn_month_data['longitude'].astype(float)
C:\Users\11823\AppData\Local\Temp\ipykernel_15768\2457463173.py:104: SettingWithCopyWarning: 
A value is trying to be set on a copy of a sli


✅ `snowAlbedo_1997_grid.csv` 找到 valid_time == 1997-06-01 的数据量: 177

✅ 站点 `CEN` `1997-06-01` 的 4 个最近网格点：
     latitude  longitude   asn  distance
905      77.2      -61.1  0.85  0.024055
907      77.1      -61.1  0.85  0.083473
906      77.2      -61.0  0.85  0.117294
908      77.1      -61.0  0.85  0.141940

✅ `snowAlbedo_1997_grid.csv` 找到 valid_time == 1997-07-01 的数据量: 177

✅ 站点 `CEN` `1997-07-01` 的 4 个最近网格点：
      latitude  longitude       asn  distance
1082      77.2      -61.1  0.850002  0.024055
1084      77.1      -61.1  0.850002  0.083473
1083      77.2      -61.0  0.850002  0.117294
1085      77.1      -61.0  0.850002  0.141940

✅ `snowAlbedo_1997_grid.csv` 找到 valid_time == 1997-08-01 的数据量: 177

✅ 站点 `CEN` `1997-08-01` 的 4 个最近网格点：
      latitude  longitude       asn  distance
1259      77.2      -61.1  0.850002  0.024055
1261      77.1      -61.1  0.850002  0.083473
1260      77.2      -61.0  0.850002  0.117294
1262      77.1      -61.0  0.850002  0.141940

✅ `snowAlbedo_1997_

C:\Users\11823\AppData\Local\Temp\ipykernel_15768\2457463173.py:102: SettingWithCopyWarning: 
A value is trying to be set on a copy of a slice from a DataFrame.
Try using .loc[row_indexer,col_indexer] = value instead

See the caveats in the documentation: https://pandas.pydata.org/pandas-docs/stable/user_guide/indexing.html#returning-a-view-versus-a-copy
  asn_month_data['latitude'] = asn_month_data['latitude'].astype(float)
C:\Users\11823\AppData\Local\Temp\ipykernel_15768\2457463173.py:103: SettingWithCopyWarning: 
A value is trying to be set on a copy of a slice from a DataFrame.
Try using .loc[row_indexer,col_indexer] = value instead

See the caveats in the documentation: https://pandas.pydata.org/pandas-docs/stable/user_guide/indexing.html#returning-a-view-versus-a-copy
  asn_month_data['longitude'] = asn_month_data['longitude'].astype(float)
C:\Users\11823\AppData\Local\Temp\ipykernel_15768\2457463173.py:104: SettingWithCopyWarning: 
A value is trying to be set on a copy of a sli


✅ `snowAlbedo_2000_grid.csv` 找到 valid_time == 2000-09-01 的数据量: 177

✅ 站点 `CEN` `2000-09-01` 的 4 个最近网格点：
      latitude  longitude       asn  distance
1436      77.2      -61.1  0.849998  0.024055
1438      77.1      -61.1  0.849998  0.083473
1437      77.2      -61.0  0.849998  0.117294
1439      77.1      -61.0  0.849998  0.141940

✅ `snowAlbedo_2001_grid.csv` 找到 valid_time == 2001-04-01 的数据量: 177

✅ 站点 `CEN` `2001-04-01` 的 4 个最近网格点：
     latitude  longitude       asn  distance
551      77.2      -61.1  0.850002  0.024055
553      77.1      -61.1  0.850002  0.083473
552      77.2      -61.0  0.850002  0.117294
554      77.1      -61.0  0.850002  0.141940

✅ `snowAlbedo_2001_grid.csv` 找到 valid_time == 2001-05-01 的数据量: 177

✅ 站点 `CEN` `2001-05-01` 的 4 个最近网格点：
     latitude  longitude       asn  distance
728      77.2      -61.1  0.850008  0.024055
730      77.1      -61.1  0.850008  0.083473
729      77.2      -61.0  0.850008  0.117294
731      77.1      -61.0  0.850008  0.141940

✅ `s

...

C:\Users\11823\AppData\Local\Temp\ipykernel_15768\2457463173.py:102: SettingWithCopyWarning: 
A value is trying to be set on a copy of a slice from a DataFrame.
Try using .loc[row_indexer,col_indexer] = value instead

See the caveats in the documentation: https://pandas.pydata.org/pandas-docs/stable/user_guide/indexing.html#returning-a-view-versus-a-copy
  asn_month_data['latitude'] = asn_month_data['latitude'].astype(float)
C:\Users\11823\AppData\Local\Temp\ipykernel_15768\2457463173.py:103: SettingWithCopyWarning: 
A value is trying to be set on a copy of a slice from a DataFrame.
Try using .loc[row_indexer,col_indexer] = value instead

See the caveats in the documentation: https://pandas.pydata.org/pandas-docs/stable/user_guide/indexing.html#returning-a-view-versus-a-copy
  asn_month_data['longitude'] = asn_month_data['longitude'].astype(float)
C:\Users\11823\AppData\Local\Temp\ipykernel_15768\2457463173.py:104: SettingWithCopyWarning: 
A value is trying to be set on a copy of a sli


✅ `snowAlbedo_2024_grid.csv` 找到 valid_time == 2024-06-01 的数据量: 177

✅ 站点 `ZAC_L` `2024-06-01` 的 4 个最近网格点：
     latitude  longitude       asn  distance
936      74.6      -21.4  0.850002  0.035224
937      74.6      -21.3  0.850002  0.078093
931      74.7      -21.4  0.850002  0.080158
932      74.7      -21.3  0.850002  0.106222

✅ `snowAlbedo_2024_grid.csv` 找到 valid_time == 2024-07-01 的数据量: 177

✅ 站点 `ZAC_L` `2024-07-01` 的 4 个最近网格点：
      latitude  longitude       asn  distance
1113      74.6      -21.4  0.850002  0.035224
1114      74.6      -21.3  0.850002  0.078093
1108      74.7      -21.4  0.850002  0.080158
1109      74.7      -21.3  0.850002  0.106222

✅ `snowAlbedo_2024_grid.csv` 找到 valid_time == 2024-08-01 的数据量: 177

✅ 站点 `ZAC_L` `2024-08-01` 的 4 个最近网格点：
      latitude  longitude       asn  distance
1290      74.6      -21.4  0.850002  0.035224
1291      74.6      -21.3  0.850002  0.078093
1285      74.7      -21.4  0.850002  0.080158
1286      74.7      -21.3  0.850002  0.1

C:\Users\11823\AppData\Local\Temp\ipykernel_15768\2457463173.py:102: SettingWithCopyWarning: 
A value is trying to be set on a copy of a slice from a DataFrame.
Try using .loc[row_indexer,col_indexer] = value instead

See the caveats in the documentation: https://pandas.pydata.org/pandas-docs/stable/user_guide/indexing.html#returning-a-view-versus-a-copy
  asn_month_data['latitude'] = asn_month_data['latitude'].astype(float)
C:\Users\11823\AppData\Local\Temp\ipykernel_15768\2457463173.py:103: SettingWithCopyWarning: 
A value is trying to be set on a copy of a slice from a DataFrame.
Try using .loc[row_indexer,col_indexer] = value instead

See the caveats in the documentation: https://pandas.pydata.org/pandas-docs/stable/user_guide/indexing.html#returning-a-view-versus-a-copy
  asn_month_data['longitude'] = asn_month_data['longitude'].astype(float)
C:\Users\11823\AppData\Local\Temp\ipykernel_15768\2457463173.py:104: SettingWithCopyWarning: 
A value is trying to be set on a copy of a sli


✅ `snowAlbedo_2023_grid.csv` 找到 valid_time == 2023-08-01 的数据量: 177

✅ 站点 `ZAC_U` `2023-08-01` 的 4 个最近网格点：
      latitude  longitude       asn  distance
1289      74.6      -21.5  0.850005  0.058199
1284      74.7      -21.5  0.850005  0.068824
1290      74.6      -21.4  0.850005  0.074826
1285      74.7      -21.4  0.850005  0.083358

✅ `snowAlbedo_2023_grid.csv` 找到 valid_time == 2023-09-01 的数据量: 177

✅ 站点 `ZAC_U` `2023-09-01` 的 4 个最近网格点：
      latitude  longitude       asn  distance
1466      74.6      -21.5  0.850002  0.058199
1461      74.7      -21.5  0.850002  0.068824
1467      74.6      -21.4  0.850002  0.074826
1462      74.7      -21.4  0.850002  0.083358

✅ `snowAlbedo_2024_grid.csv` 找到 valid_time == 2024-04-01 的数据量: 177

✅ 站点 `ZAC_U` `2024-04-01` 的 4 个最近网格点：
     latitude  longitude       asn  distance
581      74.6      -21.5  0.850002  0.058199
576      74.7      -21.5  0.850002  0.068824
582      74.6      -21.4  0.850002  0.074826
577      74.7      -21.4  0.850002  0.0

C:\Users\11823\AppData\Local\Temp\ipykernel_15768\2457463173.py:102: SettingWithCopyWarning: 
A value is trying to be set on a copy of a slice from a DataFrame.
Try using .loc[row_indexer,col_indexer] = value instead

See the caveats in the documentation: https://pandas.pydata.org/pandas-docs/stable/user_guide/indexing.html#returning-a-view-versus-a-copy
  asn_month_data['latitude'] = asn_month_data['latitude'].astype(float)
C:\Users\11823\AppData\Local\Temp\ipykernel_15768\2457463173.py:103: SettingWithCopyWarning: 
A value is trying to be set on a copy of a slice from a DataFrame.
Try using .loc[row_indexer,col_indexer] = value instead

See the caveats in the documentation: https://pandas.pydata.org/pandas-docs/stable/user_guide/indexing.html#returning-a-view-versus-a-copy
  asn_month_data['longitude'] = asn_month_data['longitude'].astype(float)
C:\Users\11823\AppData\Local\Temp\ipykernel_15768\2457463173.py:104: SettingWithCopyWarning: 
A value is trying to be set on a copy of a sli